# Tutorial - Time and Frequency Analyses

This is the third part of the ROSS tutorial. It shows how to run frequency response, unbalance response, time response, and the undamped critical speed (UCS) map on a `Rotor`.

Each analysis starts with a `.run_*` method. These methods return a results object with plot methods that use [Plotly](https://plotly.com/python/) — for example `run_freq_response().plot()`. You can store and customize the figures through the Plotly API.

Plot methods accept Pint units, see [Tutorial - Units](tutorial_units.ipynb).

In [1]:
import ross as rs
from ross.units import Q_
from ross.probe import Probe
import numpy as np

# Make sure the default renderer is set to 'notebook' for inline plots in Jupyter
import plotly.io as pio

pio.renderers.default = "notebook"

## Rotor model

Building the model is covered in [Tutorial - Assembling a Rotor](tutorial_modeling_part_2.ipynb). However, the analyses below use the built-in compressor example.


In [2]:
rotor3 = rs.compressor_example()
rotor3.plot_rotor(nodes=5)

# Section 1: Frequency Response

ROSS method to calculate the Frequency Response Function is `run_freq_response()`. This method returns the magnitude and phase in the frequency domain. The response is calculated for each node from the rotor model.

When plotting the results, you can choose to plot:
- `.plot_magnitude()`: amplitude vs frequency

- `.plot_phase()`: phase vs frequency

- `.plot_polar_bode()`: polar plot of amplitude vs phase

- `.plot()`: all

**Note**: By default, frequency response curves are drawn with a smooth spline through the sampled frequencies (`line_shape="spline"` in Plotly). The sampling itself is unchanged; if you prefer straight segments between the computed points, pass the optional `line_shape` argument to `plot_magnitude()`, for example: `line_shape="linear"`.

## 1.1 Running frequency response

To run the this analysis, use the command `run_freq_response()`. You can give a specific `speed_range` or let the program run with the default options. In this case, no arguments are needed to input.

First, let's run an example with a "user-defined" `speed_range`. Setting an array to `speed_range` will disable all the frequency spacing parameters.

In [3]:
samples = 61
speed_range = np.linspace(315, 1150, samples)  # rads/s
results1 = rotor3.run_freq_response(speed_range=speed_range)

/home/raphaelts/ross-wt-compressor-example/ross/rotor_assembly.py:2279: UserWarning: Extrapolating the coefficients of Bearing 0 outside its speed axis (418.9 to 1152 rad/s). Be careful when post-processing the results.
  warnings.warn(
/home/raphaelts/ross-wt-compressor-example/ross/rotor_assembly.py:2279: UserWarning: Extrapolating the coefficients of Seal 1 outside its speed axis (418.9 to 2094 rad/s). Be careful when post-processing the results.
  warnings.warn(
/home/raphaelts/ross-wt-compressor-example/ross/rotor_assembly.py:2279: UserWarning: Extrapolating the coefficients of Seal 2 outside its speed axis (418.9 to 2094 rad/s). Be careful when post-processing the results.
  warnings.warn(
/home/raphaelts/ross-wt-compressor-example/ross/rotor_assembly.py:2279: UserWarning: Extrapolating the coefficients of Seal 3 outside its speed axis (418.9 to 2094 rad/s). Be careful when post-processing the results.
  warnings.warn(
/home/raphaelts/ross-wt-compressor-example/ross/rotor_assembl

In [4]:
results1.speed_range.size

61

In the next section we'll check the difference between both results.

## 1.2 Plotting results - Bode Plot

We can plot the frequency response selecting the input and output degree of freedom.

- Input is the degree of freedom to be excited;
- Output is the degree of freedom to be observed.

Each shaft node has 6 local degrees of freedom (dof) $[x, y, z, \alpha, \beta, \theta]$, and each degree of freedom has it own index:
- $x$ &rarr; index 0
- $y$ &rarr; index 1
- $z$ &rarr; index 2
- $\alpha$ &rarr; index 3
- $\beta$ &rarr; index 4
- $\theta$ &rarr; index 5

To select a DoF to input and a DoF to the output, we have to use the following correlation:

$global\_dof = node\_number \cdot  dof\_per\_node + dof\_index$

For example:
node 26, global dof $y$:

In [5]:
node = 26
global_dof = node * rotor3.number_dof + 1
plot = results1.plot(inp=global_dof, out=global_dof)
plot

# converting the first plot yaxis to log scale
# plot = results1.plot(inp=global_dof, out=global_dof)
# plot.update_yaxes(type="log", row=1, col=1)
# plot

In [6]:
# plot1_2 = results1_2.plot(inp=global_dof, out=global_dof)
# plot1_2

# # converting the first plot yaxis to log scale
# plot1_2 = results1_2.plot(inp=global_dof, out=global_dof)
# plot1_2.update_yaxes(type="log", row=1, col=1)
# plot1_2

# Section 2: Unbalance Response


ROSS method to simulate the reponse to an unbalance is `run_unbalance_response()`. This method returns the unbalanced response in the frequency domain for a given magnitide and phase of the unbalance, the node where it's applied and a frequency range.

ROSS takes the magnitude and phase and converts to a complex force array applied to the given node:

$$
force = \left(\begin{array}{cc} 
F \cdot e^{j\delta}\\
-jF \cdot e^{j\delta}\\
0\\
0
\end{array}\right)
$$ 

where:
- $F$ is the unbalance magnitude;

- $\delta$ is the unbalance phase;

- $j$ is the complex number notation;

When plotting the results, you can choose to plot the:

- Bode plot options for a single degree of freedom:
    - `.plot_magnitude()`: amplitude vs frequency

    - `.plot_phase()`: phase vs frequency

    - `.plot_polar_bode()`: polar plot of amplitude vs phase

    - `.plot()`: all

- Deflected shape plot options:
    - `.plot_deflected_shape_2d()`: deflected shape 2d

    - `.plot_deflected_shape_3d()`: deflected shape 3d

    - `.plot_bending_moment()`: bending moment

    - `.plot_deflected_shape()`: all

## 2.1 Running unbalance response

To run the Unbalance Response, use the command `.unbalance_response()`

In this following example, we can obtain the response for a given unbalance and its respective phase in a selected node. Notice that it's possible to add multiple unbalances instantiating node, magnitude and phase as lists.

The method returns the force response array (complex values), the displacement magnitude (absolute value of the forced response) and the phase of the forced response.

Let's run an example with 2 unbalances in phase, trying to excite the first and the third natural vibration mode.
```text
Unbalance1: node = 29
            magnitude = 0.003
            phase = 0
            
Unbalance2: node = 33
            magnitude = 0.002
            phase = 0
```

In [7]:
n1 = 29
m1 = 0.003
p1 = 0

n2 = 33
m2 = 0.002
p2 = 0

frequency_range = np.linspace(315, 1150, 101)
results2 = rotor3.run_unbalance_response([n1, n2], [m1, m2], [p1, p2], frequency_range)

## 2.2 Plotting results

### 2.2.1 Bode Plot

To display the bode plot, use the command `.plot(probe)`

Where `probe` is a list of Probe objects that allows you to choose not only the node where to observe the response, but also the orientation.

Probe orientation equals 0° refers to `+X` direction (DoFX), and probe orientation equals 90° (or $\frac{\pi}{2} rad$) refers to `+Y` direction (DoFY).

You can insert multiple probes at once.

In [8]:
# probe = Probe(probe_node, probe_orientation)
probe1 = Probe(15, Q_(45, "deg"))  # node 15, orientation 45°
probe2 = Probe(35, Q_(45, "deg"))  # node 35, orientation 45°

results2.plot(probe=[probe1, probe2])

# converting the first plot yaxis to log scale
# plot2 = results2.plot(probe=[probe1, probe2])
# plot2.update_yaxes(type="log", row=1, col=1)
# plot2

### 2.2.2 Deflected shape

To display the deflected shape configuration, use the command `.plot_deflected_shape()`:


In [9]:
results2.plot_deflected_shape(speed=649)

# Section 3: Clearance Analysis

In this section, we check the unbalance response against the running clearances of the machine, following API 617 (9th edition, 6.8.2.10 and 6.8.2.11). The check answers whether the rotor can pass through its critical speeds without touching bearings, seals or impeller eyes when the vibration at the probes is as large as the mechanical test allows.

The procedure is:

1. Compute the unbalance response over the speed range with the API 617 unbalance for the mode of interest (2 × Ur, placed at the antinodes of the mode shape; see `Rotor.api617_unbalance`);
2. Compute the vibration limit $A_{vl} = \min\left(25.4,\ 25.4 \sqrt{12000 / N_{mc}}\right)$ µm peak to peak;
3. Take $A_{max}$ as the largest peak-to-peak amplitude at the vibration probes between the minimum allowable speed $N_{ma}$ and the maximum continuous speed $N_{mc}$;
4. Scale the major-axis peak-to-peak amplitude at every close-clearance location by $S_{cc} = A_{vl} / A_{max}$ (API 617 caps $S_{cc}$ at 6; pass `scale_factor_cap=6` to apply it);
5. Compare the scaled amplitudes with 75 % of the minimum diametral running clearance at each location, at the worst speed of the range.

The close-clearance locations are read from the rotor: every bearing or seal element with a `radial_clearance` (fluid-film bearings and gas seals carry it from their geometry; plain `BearingElement` and `SealElement` accept it as an argument). Let's build a rotor with clearances:


In [10]:
steel = rs.Material(name="Steel", rho=7810, E=211e9, G_s=81.2e9)

L = 0.25
i_d = 0
o_d = 0.05
N_elem = 6

shaft_elements = [
    rs.ShaftElement(
        L=L,
        idl=i_d,
        odl=o_d,
        material=steel,
        shear_effects=True,
        rotary_inertia=True,
        gyroscopic=True,
    )
    for _ in range(N_elem)
]

disk = rs.DiskElement(n=3, m=32.58, Ip=0.178, Id=0.329)

bearing0 = rs.BearingElement(
    n=0, kxx=1e6, cxx=1e3, radial_clearance=Q_(100, "um"), tag="Bearing DE"
)
bearing1 = rs.BearingElement(
    n=6, kxx=1e6, cxx=1e3, radial_clearance=Q_(120, "um"), tag="Bearing NDE"
)
eye_seal = rs.SealElement(
    n=3, kxx=0, cxx=0, radial_clearance=Q_(300, "um"), tag="Impeller eye"
)

rotor_with_clearance = rs.Rotor(
    shaft_elements=shaft_elements,
    disk_elements=[disk],
    bearing_elements=[bearing0, bearing1, eye_seal],
)

The vibration probes are passed as `Probe` objects at the same location and orientation as in the machine, because $A_{max}$ is taken over them. The speed range should go from zero to the trip speed:


In [11]:
probes = [
    rs.Probe(0, Q_(45, "deg"), tag="Probe DE"),
    rs.Probe(6, Q_(45, "deg"), tag="Probe NDE"),
]

results_c = rotor_with_clearance.run_clearance_analysis(
    speed_range=Q_(np.linspace(0, 10000, 201), "RPM"),
    minimum_allowable_speed=Q_(7000, "RPM"),
    maximum_continuous_speed=Q_(9000, "RPM"),
    probes=probes,
    mode=0,  # first forward mode
)

print("Unbalance nodes:", results_c.unbalance_node)
print("Unbalance (g·mm):", Q_(results_c.unbalance_magnitude, "kg*m").to("g*mm").m)
print(f"Avl = {results_c.vibration_limit * 1e6:.1f} µm pk-pk")
print(f"Amax = {results_c.max_probe_amplitude * 1e6:.1f} µm pk-pk")
print(f"Scc = {results_c.scale_factor:.2f}")
results_c.data()

/home/raphaelts/ross-wt-compressor-example/.venv/lib/python3.13/site-packages/scipy/_lib/_util.py:1138: LinAlgWarning: Diagonal number 39 is exactly zero. Singular matrix.
  return f(*arrays, *other_args, **kwargs)


Unbalance nodes: [3]
Unbalance (g·mm): [78.43286985]
Avl = 25.4 µm pk-pk
Amax = 7.8 µm pk-pk
Scc = 3.26


,tag,node,position (m),diametral clearance (um),limit 75% (um),max amplitude pp (um),speed at max (RPM),% of limit,status
0,Bearing DE,0,0.00,200.0,150.0,75.605786,1100.0,50.403857,OK
1,Impeller eye,3,0.75,600.0,450.0,224.597824,1100.0,49.910628,OK
2,Bearing NDE,6,1.50,240.0,180.0,75.605786,1100.0,42.003214,OK


`plot()` shows, for each location, the minimum diametral clearance, the 75 % limit and the largest scaled peak-to-peak amplitude, with the amplitude as a percentage of the limit and of the clearance:


In [12]:
results_c.plot()

`plot_response()` shows the scaled amplitude at each location against speed, with the limit of each location as a dashed line, and `plot_probe_response()` shows the unscaled probe response with $A_{vl}$ and the $N_{ma}$–$N_{mc}$ range used for $A_{max}$:


In [13]:
results_c.plot_response()

In [14]:
results_c.plot_probe_response()

# Section 4: Time Response

ROSS method to calculate displacements due a force in time domain is `run_time_response()`. This function will take a rotor object and plot its time response given a force and a time array.

There are two ways to obtain the numerical solution: 
- one by solving the system of equations in state space, and 
- the other by numerical integration using the Newmark method.

The force input must be a matrix $M \times N$, where:
- $M$ is the size of the time array;
- $N$ is the rotor's number of DoFs (you can access this value via attribute `.ndof`).

Each row from the matrix represents a node, and each column represents a time step.

Time Response allows you to plot the response for:
- a list of probes
- an orbit for a given node (2d plot)
- all the nodes orbits (3d plot)

## 4.1 Running time response in state space

To run the Time Response, use the command `.run_time_response()`.

Building the force matrix is not trivial. We recommend creating a matrix of zeros using `numpy.zeros()` and then, adding terms to the matrix. 

### 4.1.1 Considering harmonic force
In this example, let's create an harmonic force on node 26, in $x$ and $y$ directions. We'll plot results from 0 to 16 seconds of simulation.

In [15]:
time_samples = 1001
t = np.linspace(0, 16, time_samples)
speed = 600.0
node = 26

F = np.zeros((time_samples, rotor3.ndof))

# component on direction x
F[:, node * rotor3.number_dof + 0] = 10 * np.cos(2 * t)
# component on direction y
F[:, node * rotor3.number_dof + 1] = 10 * np.sin(2 * t)

response3 = rotor3.run_time_response(speed, F, t)

### 4.1.2 Plotting results

There three different options to plot the time response:

- `.plot_1d()`: plot time response for given probes.

- `.plot_2d()`: plot orbit of a selected node of a rotor system.

- `.plot_3d()`: plot orbits for each node on the rotor system in a 3D view.

The plotting methods can also select a time window without rerunning the simulation. The window is applied to the stored response after `run_time_response()` finishes.

For a regular time window, provide both `t_initial` and `t_final`. Plain numbers are read in the plot's `time_units` (seconds by default; `plot_2d` and `plot_3d` always use seconds), and values with units, such as `Q_(500, "ms")`, are also accepted:

```python
response3.plot_1d(
    probe=[probe1, probe2],
    t_initial=4.0,
    t_final=8.0,
)

response3.plot_1d(
    probe=[probe1, probe2],
    t_initial=4000,
    t_final=8000,
    time_units="ms",
)

response3.plot_2d(
    node=26,
    t_initial=4.0,
    t_final=8.0,
)

response3.plot_3d(t_initial=4.0, t_final=8.0)
```

To select one shaft revolution, use `one_revolution=True`. The result stores the `speed` given to `run_time_response()`, and the revolution is the time the shaft takes to turn 2π rad at that speed. When the speed varies along the response, the varying speed is integrated.

A window must hold at least 10 samples. At 600 rad/s a revolution lasts 2π/600 ≈ 10.5 ms, shorter than the 16 ms time step of `response3`, so `one_revolution=True` raises a `ValueError` for it. A response with 50 time steps per revolution and a force that rotates at the shaft speed shows a steady orbit:

```python
dt_fine = 2 * np.pi / speed / 50
t_fine = np.arange(0, 2, dt_fine)

F_fine = np.zeros((len(t_fine), rotor3.ndof))
F_fine[:, node * rotor3.number_dof + 0] = 10 * np.cos(speed * t_fine)
F_fine[:, node * rotor3.number_dof + 1] = 10 * np.sin(speed * t_fine)

response3_fine = rotor3.run_time_response(speed, F_fine, t_fine)

# Last shaft revolution of the response
response3_fine.plot_1d(probe=[probe1, probe2], one_revolution=True)
response3_fine.plot_2d(node=26, one_revolution=True)
response3_fine.plot_3d(one_revolution=True)
```

A revolution can be anchored by providing only one boundary. With `t_initial`, the revolution starts at that time; with `t_final`, it ends at that time:

```python
response3_fine.plot_2d(node=26, one_revolution=True, t_initial=1.0)
response3_fine.plot_3d(one_revolution=True, t_final=1.5)
```

Do not provide both `t_initial` and `t_final` together with `one_revolution=True`. Use a regular time window when both boundaries must be fixed explicitly. 

#### 4.1.2.1 Ploting time response for list of probes

In [16]:
probe1 = Probe(3, 0)  # node 3, orientation 0° (X dir.)
probe2 = Probe(3, Q_(90, "deg"))  # node 3, orientation 90°(Y dir.)

response3.plot_1d(probe=[probe1, probe2])

#### 4.1.2.2 Ploting orbit response for a single node

In [17]:
response3.plot_2d(node=26)

#### 4.1.2.3 Ploting orbit response for all nodes

In [18]:
response3.plot_3d()

### 4.1.3 Considering coded force methods

In this example, we consider two forces of excitation:

- Unbalance Force ($F_{unb}$): The method `.unbalance_force_over_time()` calculates this time-varying force and returns a force array of shape `(ndof, len(t))`.

- Weight ($W$): The method `.gravitational_force()` returns a static force array of shape `(ndof,)`, which must be expanded to match the time dimension.

- Force Combination: 
$
F(t) = F_{unb}(t) + W
$

In [19]:
dt = 1e-3
t = np.arange(0, 16, dt)
speed = 600.0
node = 29

# Unbalance force
Funb = rotor3.unbalance_force_over_time(
    node=[node], magnitude=[0.003], phase=[0], omega=speed, t=t
)

# Weight
W = rotor3.gravitational_force(direction="y")

# Force combination
F = (Funb + W[:, np.newaxis]).T  # F argument has shape (len(t), ndof)

response3_2 = rotor3.run_time_response(speed, F, t)

response3_2.plot_dfft(
    probe=[Probe(node, 0), Probe(node, Q_(90, "deg"))], frequency_units="rad/s"
)

## 4.2 Running time response with Newmark method

To run the Time Response in this case, use the command `.run_time_response()` with the argument `method="newmark"`.

One of the advantages of this method is that we can consider an array of rotor velocities as a function of time, rather than just a constant velocity. Additionally, we can pass a callable function as an argument that returns an array of forces to be added to the right-hand side of the system of equations.



### 4.2.1 Considering speed variation

To illustrate this, let’s now consider just an unbalance force applied at node 29, with a run-up to 600 rad/s over 3 seconds.

In [20]:
dt = 1e-3
t = np.arange(0, 3, dt)
speed = np.linspace(0, 600.0, len(t))
node = 29

Funb = rotor3.unbalance_force_over_time(
    node=[node], magnitude=[0.003], phase=[0], omega=speed, t=t
)

F = Funb.T

response3_n1 = rotor3.run_time_response(speed, F, t, method="newmark")

response3_n1.plot_1d(probe=[Probe(node, 0), Probe(node, Q_(90, "deg"))])

### 4.2.2 Custom external forces with `add_to_RHS`

The `add_to_RHS` argument allows the user to dynamically modify the external force array applied to the rotor during time integration. In addition to a predefined force array $F$, an additional contribution can be introduced at each time step through a custom function, for example `calc_force`.

This function is called automatically at every time step of the simulation and receives the following arguments:
- `step`: Current step index in the simulation.

- `time_step`: Current simulation time.

- `disp_resp`: Displacement response at the current step (useful if the force depends on displacement).

- `velc_resp`: Velocity response at the current step.

- `accl_resp`: Acceleration response at the current step.  

The function must return the additional force array for that time step. This enables the implementation of forces that are nonlinear or state-dependent (e.g. feedback control, impact forces).


For example:

In [21]:
def calc_force(step, time_step, disp_resp, velc_resp, accl_resp, args):
    # Example: Add a damping-dependent force
    damping_force = -0.01 * velc_resp
    return damping_force


response3_n2 = rotor3.run_time_response(
    speed,
    F,
    t,
    method="newmark",
    add_to_RHS=calc_force,
)

## 4.3 Harmonic Balance Method (HBM)

The Harmonic Balance Method (HBM) enables the computation of steady-state periodic responses of rotor systems subjected to harmonic excitations.
Unlike traditional time-domain integration methods, HBM determines the system response directly in the frequency domain, providing an efficient and accurate approach for steady-state vibration analysis.

To run the Harmonic Balance Method, use the command `.run_harmonic_balance_response()`.

This routine computes the steady-state harmonic response and provides post-processing tools for:
- Frequency-domain analysis;
- Time-domain reconstruction.

Compared to the conventional `.run_time_response()` approach, the execution time of `.run_harmonic_balance_response()` is significantly reduced, since it avoids numerical integration over time. This emphasizes the computational efficiency of the Harmonic Balance approach for steady-state analyses.

The current implementation follows the methodology proposed by {cite:t}`cunha2025`.

### 4.3.1 Running

Consider a rotor system subjected to the following harmonic excitation forces:

$$
F_{x,29}(t) = A_1 \cos(\omega t + p_1) + A_2 \cos(2\omega t + p_2) + A_3 \cos(3\omega t + p_3),
$$

$$
F_{y,29}(t) = A_1 \sin(\omega t + p_1) + A_2 \sin(2\omega t + p_2) + A_3 \sin(3\omega t + p_3),
$$

$$
F_{x,33}(t) = m \, e \, \omega^2 \cos(\omega t),
$$

$$
F_{y,33}(t) = m \, e \, \omega^2 \sin(\omega t).
$$

These expressions represent a combination of multi-harmonic excitations applied at node 29, and a classical unbalance excitation applied at node 33, where $\omega$ is rotational angular frequency (rad/s), $t$ is time (s), $A$ is force amplitude (N), $p$ is phase angle (rad), $m$ is unbalance mass (kg), and $e$ is eccentricity of the unbalance (m).

In [22]:
# Rotor operating speed (rad/s)
speed = 200.0

# Time vector for reconstruction
t = np.arange(0, 10, 1e-4)

# Harmonic excitation parameters
A1, A2, A3 = 1.0, 10.0, 5.0  # Force amplitudes (N)
p1, p2, p3 = 0.0, 0.0, 0.0  # Phase angles (rad)
m, e = 0.2, 0.01  # Unbalance mass (kg) and eccentricity (m)

# Define probe for observation
probe = rs.Probe(15, rs.Q_(45, "deg"))

# Run Harmonic Balance Analysis
hb_results = rotor3.run_harmonic_balance_response(
    speed=speed,
    t=t,
    harmonic_forces=[
        {
            "node": 29,
            "magnitudes": [A1, A2, A3],
            "phases": [p1, p2, p3],
            "harmonics": [1, 2, 3],
        },
        {"node": 33, "magnitudes": [m * e * speed**2], "phases": [0], "harmonics": [1]},
    ],
    n_harmonics=3,  # Number of harmonics considered in the HBM solution
)

### 4.3.2 Plotting frequency-domain response

In [23]:
hb_fig = hb_results.plot([probe], frequency_units="Hz")
hb_fig

### 4.3.3 Plotting deflected shape

In [24]:
hb_results.plot_deflected_shape()

### 4.3.4 Time-domain reconstruction of the steady-state response

In [25]:
hb_time_resp = hb_results.get_time_response()
hb_time_resp.plot_1d([probe])

### 4.3.5  Comparison – Harmonic Balance vs. DFFT Spectrum

In [26]:
hb_time_resp.plot_dfft(
    probe=[rs.Probe(15, rs.Q_(45, "deg"), tag="DFFT")],
    frequency_units="Hz",
    frequency_range=(0, 100),
    yaxis_type="log",
    fig=hb_fig,
)

# Section 5: Undamped Critical Speed Map (UCS)

This method will plot the undamped critical speed map for a given range of stiffness values. If the range is not provided, the bearing stiffness at rated speed will be used to create a range.

Whether a synchronous analysis is desired, the method selects only the foward modes and the frequency of the first forward mode will be equal to the speed.

To run the UCS Map, use the command `.plot_ucs()`.

## 5.1 Running

In this example the UCS Map is calculated for a stiffness range from **10E6** to **10E11** N/m. The other options are left to default.


In [27]:
stiff_range = (6, 11)
ucs_results = rotor3.run_ucs(stiffness_range=stiff_range, num=20, num_modes=16)

## 5.2 Plotting

In [28]:
ucs_fig = ucs_results.plot()
ucs_fig

# References

```{bibliography}
:filter: docname in docnames
```